In [1]:
%cd /workspaces/Pointcept
from pointcept.engines.defaults import  default_setup
from pointcept.engines.defaults import (
    default_argument_parser,
    default_config_parser,
)
from pointcept.engines.train import TRAINERS
import torch
import numpy as np

/workspaces/Pointcept


/opt/conda/lib/python3.10/site-packages/timm/models/layers/__init__.py:48: FutureWarning: Importing from timm.models.layers is deprecated, please import via timm.layers
  warnings.warn(f"Importing from {__name__} is deprecated, please import via timm.layers", FutureWarning)


In [2]:
args = default_argument_parser().parse_args(
"""
--config-file /workspaces/Pointcept/configs/scannet/pipeline-sculpting-ptv3.py 
--num-gpus 0 
--options num_workers=0 num_worker_per_gpu=0 batch_size=1 
          weight=/workspaces/Pointcept/artifacts/spu8by4j-model_last:v80""".split()
)
cfg = default_config_parser(args.config_file, args.options)

In [3]:
cfg = default_setup(cfg)
#cfg.num_worker_per_gpu=0
trainer = TRAINERS.build(dict(type=cfg.train.type, cfg=cfg))

[2025-05-12 18:12:24,853 INFO train.py line 134 719] => Loading config ...
[2025-05-12 18:12:24,854 INFO train.py line 136 719] Save path: exp/default
[2025-05-12 18:12:24,986 INFO train.py line 137 719] Config:
weight = '/workspaces/Pointcept/artifacts/spu8by4j-model_last:v80'
resume = False
evaluate = False
test_only = False
seed = 24623706
save_path = 'exp/default'
num_worker = 32
batch_size = 1
batch_size_val = None
batch_size_test = None
epoch = 100
eval_epoch = 100
clip_grad = None
sync_bn = False
enable_amp = True
amp_dtype = 'float16'
empty_cache = False
empty_cache_per_epoch = False
find_unused_parameters = False
mix_prob = 0.8
param_dicts = [dict(keyword='block', lr=0.0006)]
hooks = [
    dict(type='CheckpointLoaderAllowMismatch'),
    dict(type='IterationTimer', warmup_iter=2),
    dict(type='InformationWriter'),
    dict(type='SemSegEvaluator')
]
train = dict(type='DefaultTrainer')
test = dict(type='SemSegPredictor', verbose=True)
sculpting_transform = dict(
    type='Sculp

In [4]:
train_loader = trainer.train_loader
i, b = next(enumerate(train_loader))

b

{'coord': tensor([[ 2.8539,  0.2113,  1.5950],
         [ 2.8542,  0.1929,  1.5991],
         [ 2.8460,  0.1802,  1.7113],
         ...,
         [-2.2321,  1.0840, -0.1005],
         [-2.2168,  1.0793, -0.0969],
         [-2.2278,  1.0614, -0.0945]]),
 'grid_coord': tensor([[286, 135,  95],
         [286, 134,  95],
         [286, 134, 101],
         ...,
         [ 32, 179,  10],
         [ 32, 179,  11],
         [ 32, 178,  11]]),
 'segment': tensor([1, 1, 1,  ..., 1, 1, 1]),
 'offset': tensor([150167]),
 'feat': tensor([[0.5365, 0.4895, 0.5300],
         [0.5374, 0.4595, 0.4799],
         [0.5421, 0.4161, 0.3456],
         ...,
         [0.5043, 0.4937, 0.3604],
         [0.4341, 0.4340, 0.3946],
         [0.5297, 0.4024, 0.4100]])}

In [5]:
b.keys()

dict_keys(['coord', 'grid_coord', 'segment', 'offset', 'feat'])

In [ ]:
from pointcept.utils.events import EventStorage, ExceptionWriter
import pointcept.utils.comm as comm

with EventStorage() as trainer.storage, ExceptionWriter():
    # => before train
    trainer.before_train()
    trainer.logger.info(">>>>>>>>>>>>>>>> Start Training >>>>>>>>>>>>>>>>")
    for trainer.epoch in range(100):
        # => before epoch
        trainer.model.train()
        trainer.data_iterator = enumerate(trainer.train_loader)
        trainer.before_epoch()
        # => run_epoch
        for (
            trainer.comm_info["iter"],
            trainer.comm_info["input_dict"],
        ) in trainer.data_iterator:
            # => before_step
            trainer.before_step()
            # => run_step
            trainer.run_step()
            # => after_step
            trainer.after_step()
        # => after epoch
        trainer.after_epoch()
    # => after train
    trainer.after_train()

[2025-05-12 18:12:31,607 INFO misc.py line 231 719] => Loading checkpoint & weight ...
[2025-05-12 18:12:31,608 INFO misc.py line 233 719] No weight found at: /workspaces/Pointcept/artifacts/spu8by4j-model_last:v80
[2025-05-12 18:12:31,609 INFO 2646298968.py line 7 719] >>>>>>>>>>>>>>>> Start Training >>>>>>>>>>>>>>>>
[2025-05-12 18:12:38,926 INFO misc.py line 117 719] Train: [1/100][1/1613] Data 0.330 (0.330) Batch 6.975 (6.975) Remain 312:30:53 loss: 0.8325 Lr: 0.00060
[2025-05-12 18:12:39,115 INFO misc.py line 117 719] Train: [1/100][2/1613] Data 0.003 (0.003) Batch 0.188 (0.188) Remain 08:25:59 loss: 0.6552 Lr: 0.00060
[2025-05-12 18:12:39,383 INFO misc.py line 117 719] Train: [1/100][3/1613] Data 0.003 (0.003) Batch 0.268 (0.268) Remain 12:01:21 loss: 0.5702 Lr: 0.00060
[2025-05-12 18:12:39,551 INFO misc.py line 117 719] Train: [1/100][4/1613] Data 0.003 (0.003) Batch 0.168 (0.168) Remain 07:31:25 loss: 0.4640 Lr: 0.00060
[2025-05-12 18:12:39,731 INFO misc.py line 117 719] Train: 

In [9]:
trainer.comm_info["model_output_dict"]

{'loss': tensor(0.3574, device='cuda:0', grad_fn=<AddBackward0>)}